# EnCodec: neural audio compression

This example demonstrates the pretrained **24 kHz mono EnCodec** model using Hugging Face Transformers. EnCodec converts an audio waveform into discrete codes using a neural encoder and **residual vector quantization (RVQ)**, then reconstructs audio with a neural decoder.

The notebook compares different target bitrates, illustrates the role of the RVQ codebooks, and distinguishes **estimated payload bitrate** from Python tensor-file size. All operations are demonstrated, not left as student exercises.

**Requirements:** `numpy`, `soundfile`, `scipy`, `torch`, `transformers`, and `IPython`. If needed: `pip install numpy soundfile scipy torch transformers ipython`. Loading the pretrained model requires network access on the first run (or a local cached copy).

## 1. Load and listen to an audio signal

The 24 kHz EnCodec model requires a **mono signal at 24,000 samples/s**. A stereo recording is converted to mono by averaging its channels; resampling is performed **before** passing the samples to the processor. A reproducible harmonic signal is used if the course audio file is not available.

In [1]:
from pathlib import Path
import math
import numpy as np
import soundfile as sf
from scipy.signal import resample_poly
import torch
from IPython.display import Audio, display
from transformers import AutoProcessor, EncodecModel

MODEL_ID = "facebook/encodec_24khz"
SAMPLE_RATE = 24_000
AUDIO_PATH = Path("../sounds/721313-hangpan.wav")

if AUDIO_PATH.is_file():
    waveform, input_sr = sf.read(AUDIO_PATH, dtype="float32", always_2d=True)
    # soundfile convention: (samples, channels); EnCodec 24 kHz is mono.
    waveform = waveform.mean(axis=1)
    if input_sr != SAMPLE_RATE:
        # Rational resampling, with an anti-aliasing low-pass filter.
        divisor = math.gcd(int(input_sr), SAMPLE_RATE)
        waveform = resample_poly(waveform, SAMPLE_RATE // divisor, int(input_sr) // divisor)
    source_label = str(AUDIO_PATH)
else:
    # Self-contained fallback: not intended to imitate a particular instrument.
    duration_seconds = 4.0
    t = np.arange(round(duration_seconds * SAMPLE_RATE)) / SAMPLE_RATE
    envelope = np.exp(-0.45 * t)
    waveform = envelope * (0.55 * np.sin(2 * np.pi * 220 * t)
                           + 0.22 * np.sin(2 * np.pi * 440 * t)
                           + 0.10 * np.sin(2 * np.pi * 660 * t))
    source_label = "generated harmonic example"

waveform = np.asarray(waveform, dtype=np.float32)
assert waveform.ndim == 1 and len(waveform) > 0 and np.isfinite(waveform).all()
print(f"Source: {source_label} | {len(waveform) / SAMPLE_RATE:.2f} s | {SAMPLE_RATE} Hz | mono")
display(Audio(waveform, rate=SAMPLE_RATE, normalize=False))

Source: ../sounds/721313-hangpan.wav | 26.56 s | 24000 Hz | mono


## 2. Load the processor and model

The processor prepares the waveform (and, if necessary, a padding mask). The model is placed in evaluation mode and inference runs without gradient tracking. The model can be large and may take time to download.

In [2]:
device = torch.device("cuda" if torch.cuda.is_available() else "cpu")
processor = AutoProcessor.from_pretrained(MODEL_ID)
encodec = EncodecModel.from_pretrained(MODEL_ID).to(device).eval()

# NumPy arrays are accepted as raw audio by the processor.
inputs = processor(raw_audio=waveform, sampling_rate=SAMPLE_RATE, return_tensors="pt")
inputs = {key: value.to(device) if isinstance(value, torch.Tensor) else value
          for key, value in inputs.items()}

bandwidths = list(encodec.config.target_bandwidths)
print("Supported target bitrates (kb/s):", bandwidths)
print("Device:", device)
print("Number of RVQ entries per codebook:", encodec.config.codebook_size)

Supported target bitrates (kb/s): [1.5, 3.0, 6.0, 12.0, 24.0]
Device: cpu
Number of RVQ entries per codebook: 1024


/Users/xserra/audio-coding-materials/.venv/lib/python3.12/site-packages/torch/nn/utils/weight_norm.py:134: FutureWarning: `torch.nn.utils.weight_norm` is deprecated in favor of `torch.nn.utils.parametrizations.weight_norm`.
  WeightNorm.apply(module, name, dim)
/Users/xserra/audio-coding-materials/.venv/lib/python3.12/site-packages/transformers/models/encodec/modeling_encodec.py:120: UserWarning: To copy construct from a tensor, it is recommended to use sourceTensor.clone().detach() or sourceTensor.clone().detach().requires_grad_(True), rather than torch.tensor(sourceTensor).
  self.register_buffer("padding_total", torch.tensor(kernel_size - stride, dtype=torch.int64), persistent=False)


## 3. Encode and reconstruct at a selected bitrate

`encode()` returns **integer indices** into learned codebooks, plus optional scale factors. The usual code tensor has shape `(batch, frames, codebooks, time_steps)`. Some models segment a long waveform into multiple frames. The decoder turns those indices back into audio.

An **RVQ codebook** represents one refinement stage; more active codebooks normally allow a higher rate and more accurate reconstruction. The quantized codes themselves are not waveform samples.

In [3]:
def encode_at(bandwidth_kbps):
    """Run the pretrained encoder at one of the supported target bitrates."""
    with torch.inference_mode():
        return encodec.encode(**inputs, bandwidth=float(bandwidth_kbps))


def decode_outputs(encoded):
    """Decode tokens and return a 1-D NumPy waveform at 24 kHz."""
    with torch.inference_mode():
        decoded = encodec.decode(
            audio_codes=encoded.audio_codes,
            audio_scales=encoded.audio_scales,
            padding_mask=inputs.get("padding_mask"),
        ).audio_values
    # The model may pad the last frame; compare only valid original samples.
    return decoded.detach().cpu().numpy().reshape(-1)[:len(waveform)]

chosen_kbps = bandwidths[-1]
encoded = encode_at(chosen_kbps)
reconstructed = decode_outputs(encoded)
print("Encoded code tensor shape:", tuple(encoded.audio_codes.shape))
print(f"Target rate: {chosen_kbps} kb/s | Decoded duration: {len(reconstructed)/SAMPLE_RATE:.2f} s")

# Use identical playback gain. The peak limiter avoids browser clipping.
playback_gain = min(1.0, 0.95 / max(np.max(np.abs(waveform)),
                                      np.max(np.abs(reconstructed)), 1e-12))
print("Original")
display(Audio(waveform * playback_gain, rate=SAMPLE_RATE, normalize=False))
print("Reconstructed")
display(Audio(reconstructed * playback_gain, rate=SAMPLE_RATE, normalize=False))

Encoded code tensor shape: (1, 1, 32, 1993)
Target rate: 24.0 kb/s | Decoded duration: 26.56 s
Original


Reconstructed


## 4. Codebook count and nominal bitrate

EnCodec represents the encoded audio with indices into learned **residual vector quantization (RVQ)** codebooks. The nominal bitrate depends on:

- **$K$**: number of entries in each codebook.
- **$Q$**: number of active RVQ codebooks per encoded time position.
- **$F$**: encoded time positions (tokens) per second.

For fixed-length binary indices, each selected entry needs $b=\lceil\log_2 K\rceil$ bits. When $K$ is a power of two, $b=\log_2 K$. The **nominal code-index payload bitrate** is therefore

$$
R_{\mathrm{tokens}} = \frac{Q\,F\,\lceil\log_2 K\rceil}{1000}\quad\text{kb/s}.
$$

For example, the 24 kHz EnCodec model uses $K=1024$ entries per codebook, so each index is **10 bits**. With $Q=32$ active codebooks and approximately $F=75$ token positions per second:

$$
R_{\mathrm{tokens}} = \frac{32\times75\times10}{1000}=24\ \text{kb/s}.
$$

**Measuring the rate from returned codes.** The code tensor generally has shape `(batch, frames, codebooks, time_steps)`, where *frames* are processing chunks and *time_steps* are encoded positions within each chunk. For one audio signal with duration $T$ seconds, count indices over **all** its chunks, codebooks, and positions:

$$
R_{\mathrm{tokens}} = \frac{\text{frames}\times\text{codebooks}\times\text{time\_steps}\times b}{1000\,T}\quad\text{kb/s}.
$$

For a batch of multiple independent signals, compute this separately for each signal; do not count the batch dimension as part of one signal's bitrate. Chunk overlap or padding can make the measured index rate differ slightly from the nominal formula.

**Important:** This is the bitrate of fixed-length **code indices**, not a measured compressed `.ecdc` file bitrate. It does not include framing, metadata, stored scales, or other overhead (and does not estimate any additional entropy coding). A `torch.save()` archive is likewise not a packed audio bitstream.

In [4]:
def token_statistics(codes, duration_s, codebook_size):
    """Estimate raw fixed-length code-index payload rate (not a container rate)."""
    if codes.ndim != 4:
        raise ValueError(f"Expected (batch, frames, codebooks, steps), got {tuple(codes.shape)}")
    if duration_s <= 0:
        raise ValueError("Duration must be positive")
    batch, frames, codebooks, steps = codes.shape
    if batch != 1:
        raise ValueError("This example estimates bitrate for one audio signal (batch=1)")
    bits_per_index = math.ceil(math.log2(int(codebook_size)))
    indices = int(frames * codebooks * steps)
    return {
        "frames": frames,
        "codebooks": codebooks,
        "tokens_per_frame": steps,
        "total_indices": indices,
        "estimated_kbps": indices * bits_per_index / duration_s / 1000,
    }

stats = token_statistics(encoded.audio_codes, len(waveform) / SAMPLE_RATE,
                         encodec.config.codebook_size)
for name, value in stats.items():
    print(f"{name}: {value}")
print(f"Target: {chosen_kbps} kb/s (may differ slightly because of padding/framing)")

frames: 1
codebooks: 32
tokens_per_frame: 1993
total_indices: 63776
estimated_kbps: 24.011859846731877
Target: 24.0 kb/s (may differ slightly because of padding/framing)


## 5. Listen at multiple bitrates

The model chooses how many residual codebooks to use for each **supported target bandwidth**. Re-encoding at the chosen bandwidth is preferable to changing an already encoded tensor when comparing operating points. Playback uses one common gain across all the examples, so volume differences are not hidden by automatic normalization.

In [5]:
# For quick demonstrations, select three representative target rates.
selected_rates = sorted(set([bandwidths[0], bandwidths[len(bandwidths)//2], bandwidths[-1]]))
results = {}
for rate in selected_rates:
    item = encode_at(rate)
    audio_out = decode_outputs(item)
    results[rate] = (item, audio_out)

# A shared gain across the source and every decoded example.
all_peaks = [float(np.max(np.abs(waveform)))] + [float(np.max(np.abs(y))) for _, y in results.values()]
common_gain = min(1.0, 0.95 / max(max(all_peaks), 1e-12))
print("Original")
display(Audio(waveform * common_gain, rate=SAMPLE_RATE, normalize=False))
for rate, (item, y) in results.items():
    s = token_statistics(item.audio_codes, len(waveform)/SAMPLE_RATE,
                         encodec.config.codebook_size)
    print(f"{rate:g} kb/s target | {s['codebooks']} RVQ codebooks | "
          f"{s['estimated_kbps']:.2f} kb/s estimated token payload")
    display(Audio(y * common_gain, rate=SAMPLE_RATE, normalize=False))

Original


1.5 kb/s target | 2 RVQ codebooks | 1.50 kb/s estimated token payload


6 kb/s target | 8 RVQ codebooks | 6.00 kb/s estimated token payload


24 kb/s target | 32 RVQ codebooks | 24.01 kb/s estimated token payload


## 6. What happens if we remove residual codebooks?

Each successive RVQ codebook supplies extra information to refine the reconstructed waveform. To illustrate this, we can keep just the **first few codebooks** of a high-rate encoding and decode the truncated codes. This is an **informal diagnostic** rather than a substitute for selecting a documented model bandwidth: in a pretrained codec, rate-dependent encoding choices may matter.

The important detail is to **decode `reduced_codes`, not the original `audio_codes`**.

In [6]:
from types import SimpleNamespace

full_codes = encoded.audio_codes
n_books = int(full_codes.shape[-2])
reduced_book_count = max(1, n_books // 4)
reduced_codes = full_codes[:, :, :reduced_book_count, :].contiguous()

with torch.inference_mode():
    reduced_audio_tensor = encodec.decode(
        audio_codes=reduced_codes,
        audio_scales=encoded.audio_scales,
        padding_mask=inputs.get("padding_mask"),
    ).audio_values
reduced_audio = reduced_audio_tensor.detach().cpu().numpy().reshape(-1)[:len(waveform)]
print(f"Full-rate codebooks: {n_books}; retained: {reduced_book_count}")
common_gain = min(1.0, 0.95 / max(float(np.max(np.abs(waveform))),
                                      float(np.max(np.abs(reconstructed))),
                                      float(np.max(np.abs(reduced_audio))), 1e-12))
print("Full-rate reconstruction")
display(Audio(reconstructed * common_gain, rate=SAMPLE_RATE, normalize=False))
print("Fewer RVQ codebooks")
display(Audio(reduced_audio * common_gain, rate=SAMPLE_RATE, normalize=False))

Full-rate codebooks: 32; retained: 8
Full-rate reconstruction


Fewer RVQ codebooks


## 7. Storing codes: container size is not codec bitrate

`torch.save()` serializes tensors and Python metadata. It is **not an EnCodec bitstream format** and is normally inefficient for these discrete indices because each index is stored using a full tensor integer data type. We can save/load a local demonstration archive, but its byte size should **not** be used as the true compression ratio of EnCodec. A production codec requires suitable bit packing, scale/frame metadata and a defined container format.

In [7]:
# Store one model output for illustration; no claim of efficient bit packing.
archive_path = Path("encodec_tensor_archive.pt")
low_rate = selected_rates[0]
low_result = results[low_rate][0]
payload = {
    "audio_codes": low_result.audio_codes.detach().cpu(),
    "audio_scales": (low_result.audio_scales.detach().cpu()
                     if isinstance(low_result.audio_scales, torch.Tensor)
                     else low_result.audio_scales),
    "sample_rate": SAMPLE_RATE,
    "num_original_samples": len(waveform),
    "target_bandwidth_kbps": float(low_rate),
    "model_id": MODEL_ID,
}
torch.save(payload, archive_path)
print(f"Serialized tensor archive: {archive_path.stat().st_size:,} bytes")
print("This is NOT a packed EnCodec elementary stream.")

# Load only the locally created archive. Use weights_only=True for safer tensor loading.
loaded = torch.load(archive_path, map_location=device, weights_only=True)
with torch.inference_mode():
    restored = encodec.decode(
        audio_codes=loaded["audio_codes"].to(device),
        audio_scales=(loaded["audio_scales"].to(device)
                      if isinstance(loaded["audio_scales"], torch.Tensor)
                      else loaded["audio_scales"]),
        padding_mask=inputs.get("padding_mask"),
    ).audio_values
restored = restored.detach().cpu().numpy().reshape(-1)[:len(waveform)]
print(f"Decoded {len(restored)} samples from the reloaded code tensors")
display(Audio(restored * common_gain, rate=SAMPLE_RATE, normalize=False))

Serialized tensor archive: 33,383 bytes
This is NOT a packed EnCodec elementary stream.
Decoded 637445 samples from the reloaded code tensors


## What to remember

- EnCodec uses a learned encoder, residual vector quantization, and a learned decoder. Its **integer code indices** are not audio samples.
- More RVQ codebooks generally mean a higher token rate and more faithful audio, though perceived quality also depends on the content and trained model.
- The 24 kHz model expects **mono audio at 24 kHz**. Resample and convert channels before inference.
- The estimated payload bitrate can be computed from the **total number of indices and bits per index**, including all frames.
- A tensor archive made by `torch.save()` is **not a packed compressed-audio bitstream** and its file size is not a valid measure of codec efficiency.
- Listen using a **shared gain**: independent normalization can obscure audible level differences.